<a href="https://colab.research.google.com/github/chervov/ProteinModelling1/blob/main/JAK2.ipynb" target="_parent"><img src="https://colab.research.google.com/assets/colab-badge.svg" alt="Open In Colab"/></a>

# Analysis of JAK2


# AF2 structure

load and plot

In [1]:
%pip install -q requests py3Dmol

from pathlib import Path
import requests
import py3Dmol

UNIPROT_ID = "O60674"  # Human JAK2


def get_json(url):
    response = requests.get(url, timeout=120)
    response.raise_for_status()
    return response.json()


# 1. Retrieve and print the canonical sequence.
uniprot = get_json(
    f"https://rest.uniprot.org/uniprotkb/{UNIPROT_ID}.json"
)
sequence = uniprot["sequence"]["value"]

print(f">JAK2_HUMAN | UniProt: {UNIPROT_ID}")
for start in range(0, len(sequence), 80):
    print(sequence[start:start + 80])

print(f"\nSequence length: {len(sequence)} amino acids")


# 2. Find the full-length AlphaFold model.
# The API supplies the current URL, avoiding a hard-coded version.
predictions = get_json(
    f"https://alphafold.ebi.ac.uk/api/prediction/{UNIPROT_ID}"
)

full_length_models = [
    model for model in predictions
    if int(model.get("uniprotStart", -1)) == 1
    and int(model.get("uniprotEnd", -1)) == len(sequence)
    and model.get("pdbUrl")
]

if not full_length_models:
    raise ValueError("No full-length AlphaFold PDB model found for JAK2.")

pdb_url = full_length_models[0]["pdbUrl"]
response = requests.get(pdb_url, timeout=120)
response.raise_for_status()
pdb_text = response.text

pdb_path = Path("/content/AF_JAK2.pdb")
pdb_path.write_text(pdb_text)

print(f"\nModel URL: {pdb_url}")
print(f"Saved to: {pdb_path}")


# 3. Interactive cartoon/ribbon visualization.
view = py3Dmol.view(width=950, height=650)
view.addModel(pdb_text, "pdb")
view.setStyle({}, {"cartoon": {"color": "spectrum"}})
view.setBackgroundColor("white")
view.zoomTo()
view.show()

>JAK2_HUMAN | UniProt: O60674
MGMACLTMTEMEGTSTSSIYQNGDISGNANSMKQIDPVLQVYLYHSLGKSEADYLTFPSGEYVAEEICIAASKACGITPV
YHNMFALMSETERIWYPPNHVFHIDESTRHNVLYRIRFYFPRWYCSGSNRAYRHGISRGAEAPLLDDFVMSYLFAQWRHD
FVHGWIKVPVTHETQEECLGMAVLDMMRIAKENDQTPLAIYNSISYKTFLPKCIRAKIQDYHILTRKRIRYRFRRFIQQF
SQCKATARNLKLKYLINLETLQSAFYTEKFEVKEPGSGPSGEEIFATIIITGNGGIQWSRGKHKESETLTEQDLQLYCDF
PNIIDVSIKQANQEGSNESRVVTIHKQDGKNLEIELSSLREALSFVSLIDGYYRLTADAHHYLCKEVAPPAVLENIQSNC
HGPISMDFAISKLKKAGNQTGLYVLRCSPKDFNKYFLTFAVERENVIEYKHCLITKNENEEYNLSGTKKNFSSLKDLLNC
YQMETVRSDNIIFQFTKCCPPKPKDKSNLLVFRTNGVSDVPTSPTLQRPTHMNQMVFHKIRNEDLIFNESLGQGTFTKIF
KGVRREVGDYGQLHETEVLLKVLDKAHRNYSESFFEAASMMSKLSHKHLVLNYGVCVCGDENILVQEFVKFGSLDTYLKK
NKNCINILWKLEVAKQLAWAMHFLEENTLIHGNVCAKNILLIREEDRKTGNPPFIKLSDPGISITVLPKDILQERIPWVP
PECIENPKNLNLATDKWSFGTTLWEICSGGDKPLSALDSQRKLQFYEDRHQLPAPKWAELANLINNCMDYEPDFRPSFRA
IIRDLNSLFTPDYELLTENDMLPNMRIGALGFSGAFEDRDPTQFEERHLKFLQQLGKGNFGSVEMCRYDPLQDNTGEVVA
VKKLQHSTEEHLRDFEREIEILKSLQHDNIVKYKGVCYSAGRRNLKLIMEYLPYGSLRDYLQKHKERIDHIKLLQYTSQ

3Dmol.js failed to load for some reason. Please check your browser console for error messages.

In [2]:
import numpy as np
import pandas as pd
import py3Dmol
from IPython.display import display

# Domain names and colours.
DOMAIN_STYLES = {
    "FERM": ("FERM", "#3498db"),
    "SH2": ("SH2", "#2ecc71"),
    "Protein kinase 1": ("JH2 pseudokinase", "#f39c12"),
    "Protein kinase 2": ("JH1 kinase", "#9b59b6"),
}

# Retrieve all domain annotations from the UniProt data.
domains = []

for feature in uniprot.get("features", []):
    if feature["type"] != "Domain":
        continue

    description = feature.get("description", "Domain")
    label, color = DOMAIN_STYLES.get(
        description, (description, "#e74c3c")
    )

    start = int(feature["location"]["start"]["value"])
    end = int(feature["location"]["end"]["value"])

    domains.append({
        "Domain": label,
        "UniProt annotation": description,
        "Start": start,
        "End": end,
        "Length": end - start + 1,
        "Color": color,
    })

if not domains:
    raise ValueError("No domain annotations found in UniProt.")

print(f"Human JAK2 — UniProt {UNIPROT_ID}")
print("Residue coordinates are 1-based; endpoints are inclusive.")
display(pd.DataFrame(domains).drop(columns="Color"))


# Read Cα coordinates for positioning domain labels.
# Full-length AlphaFold PDB numbering matches UniProt numbering.
ca_coords = {}

for line in pdb_text.splitlines():
    if (
        line.startswith("ATOM")
        and line[12:16].strip() == "CA"
        and line[21].strip() == "A"
    ):
        residue_number = int(line[22:26])
        ca_coords[residue_number] = np.array([
            float(line[30:38]),
            float(line[38:46]),
            float(line[46:54]),
        ])


# Cartoon/ribbon rendering.
view = py3Dmol.view(width=950, height=650)
view.addModel(pdb_text, "pdb")

# Residues outside annotated domains remain grey.
view.setStyle({}, {"cartoon": {"color": "#bdbdbd"}})

for domain in domains:
    start, end = domain["Start"], domain["End"]

    view.setStyle(
        {"chain": "A", "resi": list(range(start, end + 1))},
        {"cartoon": {"color": domain["Color"]}},
    )

    points = [
        ca_coords[r]
        for r in range(start, end + 1)
        if r in ca_coords
    ]

    if points:
        center = np.mean(points, axis=0)

        view.addLabel(
            domain["Domain"],
            {
                "position": {
                    "x": float(center[0]),
                    "y": float(center[1]),
                    "z": float(center[2]),
                },
                "fontSize": 16,
                "fontColor": domain["Color"],
                "backgroundColor": "white",
                "backgroundOpacity": 0.85,
                "borderColor": domain["Color"],
                "borderThickness": 1,
                "inFront": True,
            },
        )

view.setBackgroundColor("white")
view.zoomTo()
view.show()

Human JAK2 — UniProt O60674
Residue coordinates are 1-based; endpoints are inclusive.


,Domain,UniProt annotation,Start,End,Length
0,FERM,FERM,37,380,344
1,SH2; atypical,SH2; atypical,401,482,82
2,JH2 pseudokinase,Protein kinase 1,545,809,265
3,JH1 kinase,Protein kinase 2,849,1124,276


3Dmol.js failed to load for some reason. Please check your browser console for error messages.

# JAK1 for comparison

In [3]:
%pip install -q requests numpy pandas py3Dmol

from pathlib import Path
import requests
import numpy as np
import pandas as pd
import py3Dmol
from IPython.display import display

UNIPROT_ID = "P23458"  # Human JAK1


def get_json(url):
    response = requests.get(url, timeout=120)
    response.raise_for_status()
    return response.json()


# ------------------------------------------------------------
# 1. Download JAK1 sequence and annotations from UniProt
# ------------------------------------------------------------
uniprot = get_json(
    f"https://rest.uniprot.org/uniprotkb/{UNIPROT_ID}.json"
)

sequence = uniprot["sequence"]["value"]

print(f">{uniprot['uniProtkbId']} | UniProt: {UNIPROT_ID}")
for start in range(0, len(sequence), 80):
    print(sequence[start:start + 80])

print(f"\nSequence length: {len(sequence)} amino acids")


# ------------------------------------------------------------
# 2. Read domain boundaries directly from UniProt
# ------------------------------------------------------------
DOMAIN_STYLES = {
    "FERM": ("FERM", "#3498db"),
    "SH2": ("SH2", "#2ecc71"),
    "Protein kinase 1": ("JH2 pseudokinase", "#f39c12"),
    "Protein kinase 2": ("JH1 kinase", "#9b59b6"),
}

domains = []

for feature in uniprot.get("features", []):
    if feature["type"] != "Domain":
        continue

    description = feature.get("description", "Domain")
    label, color = DOMAIN_STYLES.get(
        description, (description, "#e74c3c")
    )

    start = int(feature["location"]["start"]["value"])
    end = int(feature["location"]["end"]["value"])

    domains.append({
        "Domain": label,
        "UniProt annotation": description,
        "Start": start,
        "End": end,
        "Length": end - start + 1,
        "Color": color,
    })

if not domains:
    raise ValueError("No domain annotations found.")

print("\nUniProt domains — endpoints are inclusive:")
display(pd.DataFrame(domains).drop(columns="Color"))


# ------------------------------------------------------------
# 3. Download the full-length AlphaFold model
# ------------------------------------------------------------
predictions = get_json(
    f"https://alphafold.ebi.ac.uk/api/prediction/{UNIPROT_ID}"
)

full_length_models = [
    model for model in predictions
    if int(model.get("uniprotStart", -1)) == 1
    and int(model.get("uniprotEnd", -1)) == len(sequence)
    and model.get("pdbUrl")
]

if not full_length_models:
    raise ValueError("No full-length AlphaFold PDB model found for JAK1.")

pdb_url = full_length_models[0]["pdbUrl"]

response = requests.get(pdb_url, timeout=120)
response.raise_for_status()
pdb_text = response.text

pdb_path = Path("/content/AF_JAK1.pdb")
pdb_path.write_text(pdb_text)

print(f"\nModel URL: {pdb_url}")
print(f"Saved to: {pdb_path}")


# ------------------------------------------------------------
# 4. Read Cα coordinates to position domain labels
#    Full-length AlphaFold residue numbering matches UniProt.
# ------------------------------------------------------------
ca_by_chain = {}

for line in pdb_text.splitlines():
    if not line.startswith("ATOM"):
        continue
    if line[12:16].strip() != "CA":
        continue

    chain_id = line[21].strip()
    residue_number = int(line[22:26])
    xyz = np.array([
        float(line[30:38]),
        float(line[38:46]),
        float(line[46:54]),
    ])

    ca_by_chain.setdefault(chain_id, {})[residue_number] = xyz

if not ca_by_chain:
    raise ValueError("No Cα atoms found in the downloaded PDB.")

chain_id = max(ca_by_chain, key=lambda chain: len(ca_by_chain[chain]))
ca_coords = ca_by_chain[chain_id]


# ------------------------------------------------------------
# 5. Interactive 3D cartoon/ribbon plot
# ------------------------------------------------------------
view = py3Dmol.view(width=950, height=650)
view.addModel(pdb_text, "pdb")

# Unannotated regions remain grey.
view.setStyle({}, {"cartoon": {"color": "#bdbdbd"}})

for domain in domains:
    start, end = domain["Start"], domain["End"]

    view.setStyle(
        {"chain": chain_id, "resi": list(range(start, end + 1))},
        {"cartoon": {"color": domain["Color"]}},
    )

    points = [
        ca_coords[r]
        for r in range(start, end + 1)
        if r in ca_coords
    ]

    if points:
        center = np.mean(points, axis=0)

        view.addLabel(
            domain["Domain"],
            {
                "position": {
                    "x": float(center[0]),
                    "y": float(center[1]),
                    "z": float(center[2]),
                },
                "fontSize": 16,
                "fontColor": domain["Color"],
                "backgroundColor": "white",
                "backgroundOpacity": 0.85,
                "borderColor": domain["Color"],
                "borderThickness": 1,
                "inFront": True,
            },
        )

view.setBackgroundColor("white")
view.zoomTo()
view.show()

>JAK1_HUMAN | UniProt: P23458
MQYLNIKEDCNAMAFCAKMRSSKKTEVNLEAPEPGVEVIFYLSDREPLRLGSGEYTAEELCIRAAQACRISPLCHNLFAL
YDENTKLWYAPNRTITVDDKMSLRLHYRMRFYFTNWHGTNDNEQSVWRHSPKKQKNGYEKKKIPDATPLLDASSLEYLFA
QGQYDLVKCLAPIRDPKTEQDGHDIENECLGMAVLAISHYAMMKKMQLPELPKDISYKRYIPETLNKSIRQRNLLTRMRI
NNVFKDFLKEFNNKTICDSSVSTHDLKVKYLATLETLTKHYGAEIFETSMLLISSENEMNWFHSNDGGNVLYYEVMVTGN
LGIQWRHKPNVVSVEKEKNKLKRKKLENKHKKDEEKNKIREEWNNFSYFPEITHIVIKESVVSINKQDNKKMELKLSSHE
EALSFVSLVDGYFRLTADAHHYLCTDVAPPLIVHNIQNGCHGPICTEYAINKLRQEGSEEGMYVLRWSCTDFDNILMTVT
CFEKSEQVQGAQKQFKNFQIEVQKGRYSLHGSDRSFPSLGDLMSHLKKQILRTDNISFMLKRCCQPKPREISNLLVATKK
AQEWQPVYPMSQLSFDRILKKDLVQGEHLGRGTRTHIYSGTLMDYKDDEGTSEEKKIKVILKVLDPSHRDISLAFFEAAS
MMRQVSHKHIVYLYGVCVRDVENIMVEEFVEGGPLDLFMHRKSDVLTTPWKFKVAKQLASALSYLEDKDLVHGNVCTKNL
LLAREGIDSECGPFIKLSDPGIPITVLSRQECIERIPWIAPECVEDSKNLSVAADKWSFGTTLWEICYNGEIPLKDKTLI
EKERFYESRCRPVTPSCKELADLMTRCMNYDPNQRPFFRAIMRDINKLEEQNPDIVSEKKPATEVDPTHFEKRFLKRIRD
LGEGHFGKVELCRYDPEGDNTGEQVAVKSLKPESGGNHIADLKKEIEILRNLYHENIVKYKGICTEDGGNGIKLIMEFL

,Domain,UniProt annotation,Start,End,Length
0,FERM,FERM,34,420,387
1,SH2,SH2,439,544,106
2,JH2 pseudokinase,Protein kinase 1,583,855,273
3,JH1 kinase,Protein kinase 2,875,1153,279



Model URL: https://alphafold.ebi.ac.uk/files/AF-P23458-F1-model_v6.pdb
Saved to: /content/AF_JAK1.pdb


3Dmol.js failed to load for some reason. Please check your browser console for error messages.

# Compare JAK1 and JAK2

In [5]:
# Collect information first; defer displaying the plots.
# In load_and_plot(), replace:
#     view.show()
# with:
#     # view.show()  # displayed later

models = {}
for name, accession in PROTEINS.items():
    models[name] = load_and_plot(name, accession)

# After information for BOTH proteins has been printed,
# display the figures one below the other.
for name in PROTEINS:
    print(f"\n{name} — domain-coloured 3D structure")
    models[name]["view"].show()


JAK1 | JAK1_HUMAN | UniProt ID: P23458
UniProt: https://www.uniprot.org/uniprotkb/P23458/entry
Sequence length: 1154 amino acids

>JAK1_HUMAN | P23458
MQYLNIKEDCNAMAFCAKMRSSKKTEVNLEAPEPGVEVIFYLSDREPLRLGSGEYTAEELCIRAAQACRISPLCHNLFAL
YDENTKLWYAPNRTITVDDKMSLRLHYRMRFYFTNWHGTNDNEQSVWRHSPKKQKNGYEKKKIPDATPLLDASSLEYLFA
QGQYDLVKCLAPIRDPKTEQDGHDIENECLGMAVLAISHYAMMKKMQLPELPKDISYKRYIPETLNKSIRQRNLLTRMRI
NNVFKDFLKEFNNKTICDSSVSTHDLKVKYLATLETLTKHYGAEIFETSMLLISSENEMNWFHSNDGGNVLYYEVMVTGN
LGIQWRHKPNVVSVEKEKNKLKRKKLENKHKKDEEKNKIREEWNNFSYFPEITHIVIKESVVSINKQDNKKMELKLSSHE
EALSFVSLVDGYFRLTADAHHYLCTDVAPPLIVHNIQNGCHGPICTEYAINKLRQEGSEEGMYVLRWSCTDFDNILMTVT
CFEKSEQVQGAQKQFKNFQIEVQKGRYSLHGSDRSFPSLGDLMSHLKKQILRTDNISFMLKRCCQPKPREISNLLVATKK
AQEWQPVYPMSQLSFDRILKKDLVQGEHLGRGTRTHIYSGTLMDYKDDEGTSEEKKIKVILKVLDPSHRDISLAFFEAAS
MMRQVSHKHIVYLYGVCVRDVENIMVEEFVEGGPLDLFMHRKSDVLTTPWKFKVAKQLASALSYLEDKDLVHGNVCTKNL
LLAREGIDSECGPFIKLSDPGIPITVLSRQECIERIPWIAPECVEDSKNLSVAADKWSFGTTLWEICYNGEIPLKDKTLI
EKERFYESRCRPVTPSCKELADLMTRCMNYDPNQRPFF

,Domain,UniProt annotation,Start,End,Length
0,FERM,FERM,34,420,387
1,SH2,SH2,439,544,106
2,JH2 pseudokinase,Protein kinase 1,583,855,273
3,JH1 kinase,Protein kinase 2,875,1153,279



AlphaFold model: https://alphafold.ebi.ac.uk/files/AF-P23458-F1-model_v6.pdb
Saved: /content/JAK_models/AF_JAK1.pdb

JAK1 — domain-coloured 3D structure


3Dmol.js failed to load for some reason. Please check your browser console for error messages.


JAK2 | JAK2_HUMAN | UniProt ID: O60674
UniProt: https://www.uniprot.org/uniprotkb/O60674/entry
Sequence length: 1132 amino acids

>JAK2_HUMAN | O60674
MGMACLTMTEMEGTSTSSIYQNGDISGNANSMKQIDPVLQVYLYHSLGKSEADYLTFPSGEYVAEEICIAASKACGITPV
YHNMFALMSETERIWYPPNHVFHIDESTRHNVLYRIRFYFPRWYCSGSNRAYRHGISRGAEAPLLDDFVMSYLFAQWRHD
FVHGWIKVPVTHETQEECLGMAVLDMMRIAKENDQTPLAIYNSISYKTFLPKCIRAKIQDYHILTRKRIRYRFRRFIQQF
SQCKATARNLKLKYLINLETLQSAFYTEKFEVKEPGSGPSGEEIFATIIITGNGGIQWSRGKHKESETLTEQDLQLYCDF
PNIIDVSIKQANQEGSNESRVVTIHKQDGKNLEIELSSLREALSFVSLIDGYYRLTADAHHYLCKEVAPPAVLENIQSNC
HGPISMDFAISKLKKAGNQTGLYVLRCSPKDFNKYFLTFAVERENVIEYKHCLITKNENEEYNLSGTKKNFSSLKDLLNC
YQMETVRSDNIIFQFTKCCPPKPKDKSNLLVFRTNGVSDVPTSPTLQRPTHMNQMVFHKIRNEDLIFNESLGQGTFTKIF
KGVRREVGDYGQLHETEVLLKVLDKAHRNYSESFFEAASMMSKLSHKHLVLNYGVCVCGDENILVQEFVKFGSLDTYLKK
NKNCINILWKLEVAKQLAWAMHFLEENTLIHGNVCAKNILLIREEDRKTGNPPFIKLSDPGISITVLPKDILQERIPWVP
PECIENPKNLNLATDKWSFGTTLWEICSGGDKPLSALDSQRKLQFYEDRHQLPAPKWAELANLINNCMDYEPDFRPSFRA
IIRDLNSLFTPDYELLTENDMLPNMRIGALGFSGAFED

...

3Dmol.js failed to load for some reason. Please check your browser console for error messages.


JAK1 — domain-coloured 3D structure


3Dmol.js failed to load for some reason. Please check your browser console for error messages.


JAK2 — domain-coloured 3D structure


3Dmol.js failed to load for some reason. Please check your browser console for error messages.

In [6]:
import py3Dmol

view = py3Dmol.view(width=950, height=650)
view.addModel(models["JAK2"]["pdb_text"], "pdb")

# Standard AlphaFold confidence colours.
confidence_colors = [
    (0, 50, "#FF7D45"),     # Very low confidence: orange
    (50, 70, "#FFDB13"),    # Low confidence: yellow
    (70, 90, "#65CBF3"),    # Confident: light blue
    (90, 101, "#0053D6"),   # Very high confidence: dark blue
]

for lower, upper, color in confidence_colors:
    view.setStyle(
        {"b": [lower, upper - 0.000001]},
        {"cartoon": {"color": color}},
    )

view.setBackgroundColor("white")
view.zoomTo()

print("JAK2 — AlphaFold pLDDT")
print("Dark blue: ≥90 | Light blue: 70–90 | Yellow: 50–70 | Orange: <50")
view.show()

JAK2 — AlphaFold pLDDT
Dark blue: ≥90 | Light blue: 70–90 | Yellow: 50–70 | Orange: <50


3Dmol.js failed to load for some reason. Please check your browser console for error messages.

In [7]:
import py3Dmol

pdb_text = models["JAK2"]["pdb_text"]

view = py3Dmol.view(width=950, height=650)
view.addModel(pdb_text, "pdb")
view.setStyle({}, {"cartoon": {"color": "#bdbdbd"}})

# Read each residue's pLDDT from its Cα B-factor.
groups = {}

for line in pdb_text.splitlines():
    if not line.startswith("ATOM") or line[12:16].strip() != "CA":
        continue

    chain = line[21].strip()
    residue = line[22:26].strip() + line[26].strip()
    plddt = float(line[60:66])

    if plddt >= 90:
        color = "#0053D6"     # Dark blue
    elif plddt >= 70:
        color = "#65CBF3"     # Light blue
    elif plddt >= 50:
        color = "#FFDB13"     # Yellow
    else:
        color = "#FF7D45"     # Orange

    groups.setdefault((chain, color), []).append(residue)

for (chain, color), residues in groups.items():
    view.setStyle(
        {"chain": chain, "resi": residues},
        {"cartoon": {"color": color}},
    )

view.setBackgroundColor("white")
view.zoomTo()

print("JAK2 — cartoon coloured by pLDDT")
print("Dark blue: ≥90 | Light blue: 70–<90 | Yellow: 50–<70 | Orange: <50")
view.show()

JAK2 — cartoon coloured by pLDDT
Dark blue: ≥90 | Light blue: 70–<90 | Yellow: 50–<70 | Orange: <50


3Dmol.js failed to load for some reason. Please check your browser console for error messages.

# Shan's sctructure for the

In [8]:
%pip install -q requests biopython numpy pandas py3Dmol

import io
import requests
import numpy as np
import pandas as pd
import py3Dmol

from Bio.PDB import PDBParser, PDBIO, Superimposer
from Bio.Align import PairwiseAligner
from Bio.SeqUtils import seq1
from IPython.display import display

UNIPROT_ID = "O60674"  # Human JAK2

SHAN_URL = (
    "https://raw.githubusercontent.com/chervov/ProteinModelling1/main/"
    "Shan2014JAK1JAK2/"
    "NIHMS704086-supplement-PDB_coordinates_for_JAK2_model.pdb"
)


def get_json(url):
    response = requests.get(url, timeout=120)
    response.raise_for_status()
    return response.json()


def get_text(url):
    response = requests.get(url, timeout=120)
    response.raise_for_status()
    return response.text


# ------------------------------------------------------------
# 1. UniProt sequence and domain boundaries
# ------------------------------------------------------------
uniprot = get_json(
    f"https://rest.uniprot.org/uniprotkb/{UNIPROT_ID}.json"
)
reference_sequence = uniprot["sequence"]["value"]

styles = {
    "FERM": ("FERM", "#3498db"),
    "SH2": ("SH2", "#2ecc71"),
    "Protein kinase 1": ("JH2 pseudokinase", "#f39c12"),
    "Protein kinase 2": ("JH1 kinase", "#9b59b6"),
}

domains = []

for feature in uniprot.get("features", []):
    if feature["type"] != "Domain":
        continue

    description = feature.get("description", "Domain")
    label, color = styles.get(description, (description, "#e74c3c"))

    domains.append({
        "Domain": label,
        "Start": int(feature["location"]["start"]["value"]),
        "End": int(feature["location"]["end"]["value"]),
        "Color": color,
    })

print(f"Human JAK2 — UniProt {UNIPROT_ID}")
print(f"Full-length sequence: {len(reference_sequence)} amino acids")
print("\nUniProt domain boundaries (inclusive):")
display(pd.DataFrame(domains).drop(columns="Color"))


# ------------------------------------------------------------
# 2. Download Shan and full-length AlphaFold structures
# ------------------------------------------------------------
shan_text = get_text(SHAN_URL)

predictions = get_json(
    f"https://alphafold.ebi.ac.uk/api/prediction/{UNIPROT_ID}"
)

af_models = [
    model for model in predictions
    if int(model.get("uniprotStart", -1)) == 1
    and int(model.get("uniprotEnd", -1)) == len(reference_sequence)
    and model.get("pdbUrl")
]

if not af_models:
    raise ValueError("No full-length AlphaFold model found.")

af_text = get_text(af_models[0]["pdbUrl"])

parser = PDBParser(QUIET=True)
shan_structure = parser.get_structure("Shan", io.StringIO(shan_text))
af_structure = parser.get_structure("AF", io.StringIO(af_text))


# ------------------------------------------------------------
# 3. Map PDB residues to full-length UniProt coordinates
#    This handles Shan's fragment and its PDB numbering.
# ------------------------------------------------------------
aligner = PairwiseAligner()
aligner.mode = "global"
aligner.match_score = 2
aligner.mismatch_score = -1
aligner.open_gap_score = -8
aligner.extend_gap_score = -0.5

# Permit missing N/C termini in the modeled fragment.
aligner.query_left_gap_score = 0
aligner.query_right_gap_score = 0


def map_structure(structure):
    candidates = []

    for chain in next(structure.get_models()):
        residues = [
            residue for residue in chain
            if residue.id[0] == " "
        ]
        if not residues:
            continue

        sequence = "".join(
            seq1(residue.resname, undef_code="X")
            for residue in residues
        )

        alignment = aligner.align(reference_sequence, sequence)[0]

        mapping = {}
        matches = 0

        for ref_block, query_block in zip(
            alignment.aligned[0], alignment.aligned[1]
        ):
            ref_start, ref_end = map(int, ref_block)
            query_start, query_end = map(int, query_block)

            for ref_index, query_index in zip(
                range(ref_start, ref_end),
                range(query_start, query_end),
            ):
                mapping[ref_index + 1] = residues[query_index]
                matches += (
                    reference_sequence[ref_index] == sequence[query_index]
                )

        candidates.append({
            "chain": chain.id,
            "sequence": sequence,
            "mapping": mapping,
            "matches": matches,
            "identity": matches / len(mapping) if mapping else 0,
        })

    if not candidates:
        raise ValueError("No protein chain found.")

    best = max(candidates, key=lambda item: item["matches"])

    if best["identity"] < 0.90:
        raise ValueError(
            f"Unexpectedly low identity to JAK2: {best['identity']:.1%}"
        )

    return best


shan = map_structure(shan_structure)
af = map_structure(af_structure)

print(f"\n>Shan2014_JAK2 | chain {shan['chain']!r}")
for start in range(0, len(shan["sequence"]), 80):
    print(shan["sequence"][start:start + 80])

print(f"\nShan modeled sequence length: {len(shan['sequence'])} amino acids")
print(f"Sequence identity to UniProt: {shan['identity']:.2%}")
print(
    "Mapped UniProt span: "
    f"{min(shan['mapping'])}–{max(shan['mapping'])}"
)


# ------------------------------------------------------------
# 4. Structural alignment: Shan → AlphaFold
#    Fit on all corresponding Cα atoms in JH2 and JH1.
# ------------------------------------------------------------
kinase_domains = [
    domain for domain in domains
    if domain["Domain"] in ("JH2 pseudokinase", "JH1 kinase")
]

paired_positions = [
    position
    for position in sorted(set(shan["mapping"]) & set(af["mapping"]))
    if any(
        domain["Start"] <= position <= domain["End"]
        for domain in kinase_domains
    )
    and "CA" in shan["mapping"][position]
    and "CA" in af["mapping"][position]
]

if len(paired_positions) < 3:
    raise ValueError("Insufficient corresponding Cα atoms for alignment.")

fixed_atoms = [af["mapping"][p]["CA"] for p in paired_positions]
moving_atoms = [shan["mapping"][p]["CA"] for p in paired_positions]

superimposer = Superimposer()
superimposer.set_atoms(fixed_atoms, moving_atoms)
superimposer.apply(list(shan_structure.get_atoms()))

print(
    f"\nShan → AlphaFold alignment: RMSD = {superimposer.rms:.3f} Å "
    f"({len(paired_positions)} Cα pairs; combined JH2 + JH1 fit)"
)

# Save the aligned Shan model.
pdb_io = PDBIO()
pdb_io.set_structure(shan_structure)
aligned_buffer = io.StringIO()
pdb_io.save(aligned_buffer)
aligned_shan_text = aligned_buffer.getvalue()

with open("/content/Shan_JAK2_aligned_to_AF.pdb", "w") as f:
    f.write(aligned_shan_text)


# ------------------------------------------------------------
# 5. Plot Shan's fragment with domain colours and labels
# ------------------------------------------------------------
view = py3Dmol.view(width=950, height=650)
view.addModel(aligned_shan_text, "pdb")
view.setStyle({}, {})
view.setStyle(
    {"chain": shan["chain"]},
    {"cartoon": {"color": "#bdbdbd"}},
)

coverage_rows = []

for domain in domains:
    positions = [
        p for p in range(domain["Start"], domain["End"] + 1)
        if p in shan["mapping"]
    ]

    if not positions:
        continue

    # Use actual PDB residue IDs after mapping from UniProt.
    pdb_ids = [
        f"{shan['mapping'][p].id[1]}"
        f"{shan['mapping'][p].id[2].strip()}"
        for p in positions
    ]

    view.setStyle(
        {"chain": shan["chain"], "resi": pdb_ids},
        {"cartoon": {"color": domain["Color"]}},
    )

    points = [
        shan["mapping"][p]["CA"].coord
        for p in positions
        if "CA" in shan["mapping"][p]
    ]

    if points:
        center = np.mean(points, axis=0)

        view.addLabel(
            domain["Domain"],
            {
                "position": {
                    "x": float(center[0]),
                    "y": float(center[1]),
                    "z": float(center[2]),
                },
                "fontSize": 16,
                "fontColor": domain["Color"],
                "backgroundColor": "white",
                "backgroundOpacity": 0.85,
                "borderColor": domain["Color"],
                "borderThickness": 1,
                "inFront": True,
            },
        )

    coverage_rows.append({
        "Domain": domain["Domain"],
        "UniProt start": domain["Start"],
        "UniProt end": domain["End"],
        "Residues present in Shan": len(positions),
    })

print("\nDomains present in Shan's model:")
display(pd.DataFrame(coverage_rows))

print("\nShan JAK2 — JH2 orange; JH1 purple; other regions grey")
view.setBackgroundColor("white")
view.zoomTo({"chain": shan["chain"]})
view.show()

   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 3.2/3.2 MB 32.4 MB/s eta 0:00:00
Human JAK2 — UniProt O60674
Full-length sequence: 1132 amino acids

UniProt domain boundaries (inclusive):


,Domain,Start,End
0,FERM,37,380
1,SH2; atypical,401,482
2,JH2 pseudokinase,545,809
3,JH1 kinase,849,1124



>Shan2014_JAK2 | chain 'X'
VPTXPTLQRPTHMNQMVFHKIRNEDLIFNESLGQGTFTKIFKGVRREVGDXGQLHETEVLLKVLDKAHRNYSESFFEAAS
MMSKLSHKHLVLNYGVCVCGDENILVQEFVKFGSLDTYLKKNKNCINILWKLEVAKQLAWAMHFLEENTLIHGNVCAKNI
LLIREEDRKTGNPPFIKLSDPGISITVLPKDILQERIPWVPPECIENPKNLNLATDKWSFGTTLWEICSGGDKPLSALDS
QRKLQFYEDRHQLPAPKWAELANLINNCMDYEPDFRPSFRAIIRDLNSLFTPDYELLTENDMLPNMRIGALGFSGAFEDR
DPTQFEERHLKFLQQLGKGNFGSVEMCRYDPLQDNTGEVVAVKKLQHSTEEHLRDFEREIEILKSLQHDNIVKYKGVCYS
AGRRNLKLIMEYLPYGSLRDYLQKHKERIDHIKLLQYTSQICKGMEYLGTKRYIHRDLATRNILVENENRVKIGDFGLTK
VLPQDKEYYKVKEPGESPIFWYAPESLTESKFSVASDVWSFGVVLYELFTYIEKSKSPPAEFMRMIGNDKQGQMIVFHLI
ELLKNNGRLPRPDGCPDEIYMIMTECWNNNVNQRPSFRDLALRVDQIRDNMA

Shan modeled sequence length: 612 amino acids
Sequence identity to UniProt: 99.67%
Mapped UniProt span: 520–1131

Shan → AlphaFold alignment: RMSD = 22.321 Å (541 Cα pairs; combined JH2 + JH1 fit)

Domains present in Shan's model:


/usr/local/lib/python3.13/dist-packages/Bio/Align/__init__.py:4412: BiopythonDeprecationWarning: The attribute 'query_left_gap_score' was renamed to 'left_deletion_score'. This was done to be consistent with the
AlignmentCounts object returned by the .counts method of an Alignment object.
  warnings.warn(
/usr/local/lib/python3.13/dist-packages/Bio/Align/__init__.py:4412: BiopythonDeprecationWarning: The attribute 'query_right_gap_score' was renamed to 'right_deletion_score'. This was done to be consistent with the
AlignmentCounts object returned by the .counts method of an Alignment object.
  warnings.warn(


,Domain,UniProt start,UniProt end,Residues present in Shan
0,JH2 pseudokinase,545,809,265
1,JH1 kinase,849,1124,276



Shan JAK2 — JH2 orange; JH1 purple; other regions grey


3Dmol.js failed to load for some reason. Please check your browser console for error messages.

# Same part from AF2

In [9]:
# Select AlphaFold residues corresponding to Shan's fragment.
fragment_positions = sorted(
    set(shan["mapping"]) & set(af["mapping"])
)

def pdb_residue_id(residue):
    return f"{residue.id[1]}{residue.id[2].strip()}"


fragment_ids = [
    pdb_residue_id(af["mapping"][p])
    for p in fragment_positions
]

view_af = py3Dmol.view(width=950, height=650)
view_af.addModel(af_text, "pdb")

# Hide the full protein, then display only the matching fragment.
view_af.setStyle({}, {})
view_af.setStyle(
    {"chain": af["chain"], "resi": fragment_ids},
    {"cartoon": {"color": "#bdbdbd"}},
)

for domain in domains:
    positions = [
        p for p in fragment_positions
        if domain["Start"] <= p <= domain["End"]
    ]

    if not positions:
        continue

    residue_ids = [
        pdb_residue_id(af["mapping"][p])
        for p in positions
    ]

    view_af.setStyle(
        {"chain": af["chain"], "resi": residue_ids},
        {"cartoon": {"color": domain["Color"]}},
    )

    points = [
        af["mapping"][p]["CA"].coord
        for p in positions
        if "CA" in af["mapping"][p]
    ]

    if points:
        center = np.mean(points, axis=0)

        view_af.addLabel(
            domain["Domain"],
            {
                "position": {
                    "x": float(center[0]),
                    "y": float(center[1]),
                    "z": float(center[2]),
                },
                "fontSize": 16,
                "fontColor": domain["Color"],
                "backgroundColor": "white",
                "backgroundOpacity": 0.85,
                "borderColor": domain["Color"],
                "borderThickness": 1,
                "inFront": True,
            },
        )

print(
    f"AlphaFold JAK2 — fragment matching Shan: "
    f"{len(fragment_positions)} residues"
)
print("JH2 orange; JH1 purple; other regions grey")

view_af.setBackgroundColor("white")
view_af.zoomTo({"chain": af["chain"], "resi": fragment_ids})
view_af.show()

AlphaFold JAK2 — fragment matching Shan: 612 residues
JH2 orange; JH1 purple; other regions grey


3Dmol.js failed to load for some reason. Please check your browser console for error messages.

# Centroid differences

In [10]:
import numpy as np
import pandas as pd
from IPython.display import display


# Same centroid calculation as Orianne's code.
# Coordinates are indexed by UniProt residue number.
def _centroid_for_ranges(coords_by_resseq, ranges):
    points = []

    for start, end in ranges:
        for r in range(int(start), int(end) + 1):
            if r in coords_by_resseq:
                points.append(coords_by_resseq[r])

    if not points:
        raise ValueError("No CA atoms found for requested residue ranges")

    pts = np.stack(points, axis=0)
    return np.mean(pts, axis=0)


# Domain boundaries previously retrieved from JAK2 UniProt.
domain_ranges = {}

for domain in domains:
    if domain["Domain"] == "JH2 pseudokinase":
        domain_ranges["JH2"] = [[domain["Start"], domain["End"]]]
    elif domain["Domain"] == "JH1 kinase":
        domain_ranges["JH1"] = [[domain["Start"], domain["End"]]]

if set(domain_ranges) != {"JH1", "JH2"}:
    raise ValueError("JH1/JH2 boundaries not found.")

print("JAK2 domain boundaries from UniProt:")
for name, ranges in domain_ranges.items():
    print(f"  {name}: {ranges}")


# Use the mappings established in the previous cells.
structures = {
    "AlphaFold (open comparison)": af,
    "Shan (closed comparison)": shan,
}

rows = []

for name, model in structures.items():
    coords = {
        position: np.asarray(residue["CA"].coord, dtype=np.float64)
        for position, residue in model["mapping"].items()
        if "CA" in residue
    }

    centroid_jh2 = _centroid_for_ranges(coords, domain_ranges["JH2"])
    centroid_jh1 = _centroid_for_ranges(coords, domain_ranges["JH1"])

    delta = centroid_jh1 - centroid_jh2
    distance = float(np.linalg.norm(delta))

    counts = {}
    for domain, ranges in domain_ranges.items():
        counts[domain] = sum(
            r in coords
            for start, end in ranges
            for r in range(start, end + 1)
        )

    print(f"\n{name}")
    print(f"  JH2 centroid (Å): {np.round(centroid_jh2, 3)}")
    print(f"  JH1 centroid (Å): {np.round(centroid_jh1, 3)}")
    print(f"  JH1 − JH2 vector (Å): {np.round(delta, 3)}")
    print(f"  JH2–JH1 centroid distance: {distance:.3f} Å")
    print(f"  Cα atoms used: JH2={counts['JH2']}, JH1={counts['JH1']}")

    rows.append({
        "Model": name,
        "JH2_CA_count": counts["JH2"],
        "JH1_CA_count": counts["JH1"],
        "Delta_x_A": delta[0],
        "Delta_y_A": delta[1],
        "Delta_z_A": delta[2],
        "Centroid_distance_A": distance,
    })

results_jak2 = pd.DataFrame(rows).set_index("Model")

print("\nComparison:")
display(results_jak2.round(3))

distance_difference = (
    results_jak2.iloc[0]["Centroid_distance_A"]
    - results_jak2.iloc[1]["Centroid_distance_A"]
)
print(f"\nAlphaFold minus Shan centroid distance: {distance_difference:+.3f} Å")

JAK2 domain boundaries from UniProt:
  JH2: [[545, 809]]
  JH1: [[849, 1124]]

AlphaFold (open comparison)
  JH2 centroid (Å): [ 3.3    2.201 -6.979]
  JH1 centroid (Å): [ 39.04    9.63  -34.811]
  JH1 − JH2 vector (Å): [ 35.74    7.429 -27.832]
  JH2–JH1 centroid distance: 45.904 Å
  Cα atoms used: JH2=265, JH1=276

Shan (closed comparison)
  JH2 centroid (Å): [ 5.235  8.38  -8.387]
  JH1 centroid (Å): [ 37.182   3.697 -33.46 ]
  JH1 − JH2 vector (Å): [ 31.947  -4.683 -25.073]
  JH2–JH1 centroid distance: 40.880 Å
  Cα atoms used: JH2=265, JH1=276

Comparison:


,JH2_CA_count,JH1_CA_count,Delta_x_A,Delta_y_A,Delta_z_A,Centroid_distance_A
Model,,,,,,
AlphaFold (open comparison),265,276,35.740,7.429,-27.832,45.904
Shan (closed comparison),265,276,31.947,-4.683,-25.073,40.880



AlphaFold minus Shan centroid distance: +5.023 Å
